<a href="https://colab.research.google.com/github/TheSarthakShinde/GENAI-/blob/main/genai_exp_8.ipynb" target="_parent"><img src="https://colab.research.google.com/assets/colab-badge.svg" alt="Open In Colab"/></a>

# Generate Music with an Open-Source Foundation Model (MusicGen)


**Model:** [MusicGen](https://huggingface.co/facebook/musicgen-small) by Meta AI — a pretrained,
open-source Transformer model that generates music directly from a text description.
**How:** We use the model exactly as released (a "foundation model") — no dataset, no training, no
fine-tuning. Just load it and generate.

### How it works
MusicGen is a Transformer (the same family of architecture as GPT) that was pretrained by Meta on a
large library of music. Instead of predicting the next *word*, it predicts the next *audio token* —
so generating music is really just "autocomplete for sound," guided by your text prompt. Because it's
already fully trained, we can generate brand-new music immediately, with about **10 lines of code**.

### Steps
1. Install the library
2. Load the pretrained model
3. Generate music from a text prompt
4. Listen to it / save it as a file


## Install the library

In [ ]:
!pip install -q -U transformers scipy


     ━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━ 62.4/62.4 kB 6.1 MB/s eta 0:00:00
   ━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━ 35.3/35.3 MB 57.4 MB/s eta 0:00:00


## Load the pretrained model

This downloads MusicGen (~300M parameters) the first time you run it (takes ~1 minute).

In [ ]:
from transformers import pipeline

music_generator = pipeline("text-to-audio", model="facebook/musicgen-small", device=0)
print("Model loaded and ready!")


config.json:   0%|          | 0.00/7.87k [00:00<?, ?B/s]

[transformers] Model config: pad_token_id must be `None` or an integer within the vocabulary (between 0 and 2047), got 2048. This may result in unexpected behavior.
[transformers] Model config: bos_token_id must be `None` or an integer within the vocabulary (between 0 and 2047), got 2048. This may result in unexpected behavior.


model.safetensors: reconstructing file:   0%|          |  0.00B / 2.36GB            

model.safetensors: downloading bytes:           |  0.00B            

Loading weights:   0%|          | 0/611 [00:00<?, ?it/s]

...

spiece.model: downloading bytes:           |  0.00B            

tokenizer.json:   0%|          | 0.00/2.42M [00:00<?, ?B/s]

special_tokens_map.json:   0%|          | 0.00/2.20k [00:00<?, ?B/s]

preprocessor_config.json:   0%|          | 0.00/275 [00:00<?, ?B/s]

Model loaded and ready!


## Generate music from a text prompt

Change the `prompt` below to anything you like.

In [ ]:
prompt = "an upbeat lo-fi hip-hop track with a relaxed piano melody"

output = music_generator(prompt, forward_params={"do_sample": True})

sampling_rate = output["sampling_rate"]
audio_array = output["audio"]

# Some versions return shape (num_samples,), others (1, num_samples) — handle both
if audio_array.ndim > 1:
    audio_array = audio_array[0]

print("Generated", len(audio_array) / sampling_rate, "seconds of audio.")

[transformers] Passing `generation_config` together with generation-related arguments=({'do_sample'}) is deprecated and will be removed in future versions. Please pass either a `generation_config` object OR all generation parameters explicitly, but not both.


Generated 29.94 seconds of audio.


##  Listen to it

In [ ]:
from IPython.display import Audio, display

display(Audio(audio_array, rate=sampling_rate))


## Save it as a .wav file (and download it)

In [ ]:
from scipy.io.wavfile import write

write("generated_music.wav", rate=sampling_rate, data=audio_array)
print("Saved to generated_music.wav")

from google.colab import files
files.download("generated_music.wav")


Saved to generated_music.wav


<IPython.core.display.Javascript object>

<IPython.core.display.Javascript object>

## Generate a few different styles

Just a loop over a list of prompts — same function as above, called a few times.


In [ ]:
import numpy as np

prompts = [
    "a cheerful acoustic guitar folk tune",
    "an energetic electronic dance track with a heavy bassline",
    "a calm classical piano piece",
]

for i, p in enumerate(prompts):
    print("Prompt:", p)
    out = music_generator(p, generate_kwargs={"do_sample": True})
    out_audio = np.squeeze(np.asarray(out["audio"]))
    display(Audio(out_audio, rate=out["sampling_rate"]))

Prompt: a cheerful acoustic guitar folk tune


Prompt: an energetic electronic dance track with a heavy bassline


Prompt: a calm classical piano piece


## Optional: Create an Interactive UI with Gradio

We will install `gradio` and build a simple interface where you can type any text prompt, click "Submit", and listen to the generated audio directly in the browser.

In [ ]:
!pip install -q gradio

In [ ]:
import gradio as gr
import numpy as np

def generate_music_ui(prompt):
    # Generate audio using the loaded pipeline
    output = music_generator(prompt, forward_params={"do_sample": True})

    sampling_rate = output["sampling_rate"]
    audio_array = output["audio"]

    # Normalize shape to 1D for Gradio audio output
    if audio_array.ndim > 1:
        audio_array = audio_array[0]

    # Gradio audio output expects a tuple: (sampling_rate, numpy_array)
    return (sampling_rate, audio_array)

# Create the Gradio interface
demo = gr.Interface(
    fn=generate_music_ui,
    inputs=gr.Textbox(lines=2, placeholder="Enter music prompt here...", label="Music Description"),
    outputs=gr.Audio(label="Generated Music"),
    title="🎵 MusicGen Text-to-Music Generator",
    description="Type a description of the music you want to generate (e.g., 'heavy metal guitar solo' or 'lo-fi beats for studying') and click Submit. It might take up to a minute depending on the prompt length.",
    examples=[
        ["an upbeat lo-fi hip-hop track with a relaxed piano melody"],
        ["a cheerful acoustic guitar folk tune"],
        ["an energetic electronic dance track with a heavy bassline"]
    ]
)

# Launch the UI directly inside Colab
demo.launch(share=True)

Colab notebook detected. To show errors in colab notebook, set debug=True in launch()
* Running on public URL: https://a75e54a5677c8fa244.gradio.live

This share link is temporary and will last for up to 1 week (best effort). For free permanent hosting and GPU upgrades, run `gradio deploy` from the terminal in the working directory to deploy to Hugging Face Spaces (https://huggingface.co/spaces)


In [ ]:


import gradio as gr
import numpy as np

def generate_music_ui(prompt):
    # 1. Generate audio using the loaded transformers pipeline
    output = music_generator(prompt, forward_params={"do_sample": True})

    sampling_rate = output["sampling_rate"]
    audio_array = output["audio"]

    # 2. Normalize shape to 1D array for Gradio audio output
    if audio_array.ndim > 1:
        audio_array = audio_array[0]

    # 3. Return (sampling_rate, numpy_array) tuple required by Gradio
    return (sampling_rate, audio_array)

SyntaxError: unterminated string literal (detected at line 1) (3009034303.py, line 1)

## A pretrained open-source foundation model used directly for generation

No dataset, no training loop, no GPU fine-tuning — just a pretrained open-source foundation model
used directly for generation. This is sometimes called **zero-shot generation**: the model does the
task (text → music) purely from what it already learned during pretraining.

### Want to go further?
- Try a bigger model: `"facebook/musicgen-medium"` or `"facebook/musicgen-large"` (slower, higher quality)
- Try `forward_params={"do_sample": True, "guidance_scale": 3}` to control how closely the music follows the prompt
- Fine-tune the model on your own music dataset so it learns a specific genre or style (a bigger project — ask if you'd like that notebook too)
